# XAUUSD RL Agent — Test-Set Analysis

**Purpose**: Load a trained PPO model, evaluate it on the *unseen test split*, and produce
every visualization needed for publication / YouTube presentation.

- Run cells top-to-bottom; no pipeline re-training is needed.
- All charts are interactive Plotly figures rendered inline.
- Exports go to `outputs/notebook/`.

## 0 · Setup

In [1]:
import json, os, sys, site
from pathlib import Path

# ── Windows DLL fix ────────────────────────────────────────────────────────
# In Python 3.8+, ctypes no longer searches PATH for DLLs.  VS Code's Jupyter
# kernel also strips the shell PATH.  Both mean that c10.dll's transitive
# C-level dependencies (loaded via LoadLibraryA inside the DLL, not ctypes)
# cannot be found → OSError [WinError 1114].
#
# os.add_dll_directory() fixes Python-level ctypes calls but NOT transitive
# C-level loads.  Prepending to os.environ['PATH'] fixes both.
# This block must run before any torch / stable_baselines3 import.
if os.name == 'nt':
    _sp_dirs = list(site.getsitepackages())
    try:
        _sp_dirs.append(site.getusersitepackages())
    except Exception:
        pass

    _prepend: list[str] = [str(Path(sys.executable).parent)]   # python.exe dir
    for _sp in _sp_dirs:
        _tl = Path(_sp) / 'torch' / 'lib'
        if _tl.exists():
            _prepend.append(str(_tl))
        for _p in (Path(_sp) / 'nvidia').glob('*/lib'):
            if _p.exists():
                _prepend.append(str(_p))

    os.environ['PATH'] = os.pathsep.join(_prepend) + os.pathsep + os.environ.get('PATH', '')

    # Also call add_dll_directory for Python 3.8+ ctypes security layer
    if hasattr(os, 'add_dll_directory'):
        for _d in _prepend:
            try:
                os.add_dll_directory(_d)
            except Exception:
                pass

    print('PATH prepended with:')
    for _d in _prepend:
        print(f'  {_d}')
# ──────────────────────────────────────────────────────────────────────────

import numpy as np
import pandas as pd
import plotly.io as pio

def _looks_like_project_root(path: Path) -> bool:
    return (path / 'train_ppo.py').exists() and (path / 'config.py').exists()

cwd = Path.cwd().resolve()
candidates = [cwd, cwd.parent]
ROOT = next((p for p in candidates if _looks_like_project_root(p)), None)
if ROOT is None:
    raise FileNotFoundError(
        f'Could not locate project root from {cwd}. Expected train_ppo.py and config.py.'
    )

if str(ROOT) not in sys.path:
    sys.path.insert(0, str(ROOT))
os.chdir(ROOT)

pio.renderers.default = 'notebook'   # change to 'browser' if plots don't appear inline

OUT = ROOT / 'outputs' / 'notebook'
OUT.mkdir(parents=True, exist_ok=True)
print(f'\nProject root : {ROOT}')
print(f'Output dir   : {OUT}')

ALLOW_TEST_REVEAL = True
if not ALLOW_TEST_REVEAL:
    raise RuntimeError(
        'Test split is sealed. Set ALLOW_TEST_REVEAL = True only for final holdout analysis.'
    )

PATH prepended with:
  f:\CodeTrading\Code_trading_2026\34_RL_XAUUSD\.venv\Scripts
  f:\CodeTrading\Code_trading_2026\34_RL_XAUUSD\.venv\Lib\site-packages\torch\lib

Project root : F:\CodeTrading\Code_trading_2026\34_RL_XAUUSD
Output dir   : F:\CodeTrading\Code_trading_2026\34_RL_XAUUSD\outputs\notebook


## 1 · Locate trained model

In [26]:
MODELS = ROOT / 'models'
info_path = MODELS / 'run_info.json'

if not info_path.exists():
    raise FileNotFoundError(
        f'{info_path} not found.\n'
        'Run train_ppo.py first, then come back here.'
    )

run_info = json.loads(info_path.read_text())
print('Run info:')
for k, v in run_info.items():
    print(f'  {k}: {v}')

FINAL_MODEL  = Path(run_info['model_path'])
VECNORM_PATH = Path(run_info['vecnorm_path'])
BEST_CONSISTENCY_MODEL = MODELS / 'best_model' / 'best_model.zip'

# ── Which model to use as the primary result ──────────────────────────────
# BEST_CONSISTENCY_MODEL: the checkpoint where min(train_eval_R, val_R) peaked.
#   → both legs were positive and balanced at that moment; more generalisable.
#   → this is what _post_training_eval calls "BEST" in its output.
#
# FINAL_MODEL: the last checkpoint after all training steps.
#   → may have overfit the training period (high train return, lower val/test).
#   → _post_training_eval prints this as the final equity numbers.
#
# Recommended: use BEST_CONSISTENCY_MODEL for reporting test-set results.
# Change MODEL_PATH below to FINAL_MODEL if you want to compare.

if BEST_CONSISTENCY_MODEL.exists():
    MODEL_PATH = BEST_CONSISTENCY_MODEL
    print(f'\nUsing BEST-CONSISTENCY model: {MODEL_PATH}')
    print(f'(Change MODEL_PATH = FINAL_MODEL to use the last training checkpoint instead)')
else:
    MODEL_PATH = FINAL_MODEL
    print(f'\nBest-consistency model not found — using FINAL model: {MODEL_PATH}')

Run info:
  slug: ppo_H1_sl1-1.5-2_tp1-1.5-2-3_3000k_seed42
  model_path: models\ppo_H1_sl1-1.5-2_tp1-1.5-2-3_3000k_seed42.zip
  vecnorm_path: models\ppo_H1_sl1-1.5-2_tp1-1.5-2-3_3000k_seed42_vecnorm.pkl
  decision_timeframe: H1
  sl_atr_multipliers: [1.0, 1.5, 2.0]
  tp_r_multipliers: [1.0, 1.5, 2.0, 3.0]
  total_timesteps: 3000000
  train_episode_steps: 2048
  seed: 42
  dd_penalty: 0.8
  risk_fraction: 0.005
  spread_price: 0.2
  best_model_path: models\best_model\best_model.zip
  best_model_vecnorm_path: models\best_model\best_model_vecnorm.pkl
  promoted_from_fold: 35
  gate_passed: False

Using BEST-CONSISTENCY model: F:\CodeTrading\Code_trading_2026\34_RL_XAUUSD\models\best_model\best_model.zip
(Change MODEL_PATH = FINAL_MODEL to use the last training checkpoint instead)


## 2 · Load data & build splits

In [27]:
from config import CFG
from data_loader import load_mt_ohlcv_csv, resample_ohlcv, split_train_val_test
from features import prepare_feature_frame

print(f'Timeframe : {CFG.decision_timeframe}  ({CFG.pandas_tf})')
print(f'Embargo   : {CFG.split_embargo_bars} bars')
print('Loading M1 data …')

m1 = load_mt_ohlcv_csv(
    CFG.csv_path, time_col=CFG.time_col, source_tz=CFG.source_tz,
    start_date=CFG.start_date, end_date=CFG.end_date,
    max_days_for_demo=CFG.max_days_for_demo,
)
decision  = resample_ohlcv(m1, CFG.pandas_tf)
feat, feature_cols = prepare_feature_frame(
    decision, warmup_bars=CFG.warmup_bars,
    atr_period=CFG.atr_period, rsi_period=CFG.rsi_period,
)
train_feat, val_feat, test_feat = split_train_val_test(
    feat, train_frac=CFG.train_frac, val_frac=CFG.val_frac,
    embargo_bars=CFG.split_embargo_bars,
)

def _m1_slice(df):
    return m1.loc[(m1.index > df.index.min()) & (m1.index <= df.index.max())]

train_m1 = _m1_slice(train_feat)
val_m1   = _m1_slice(val_feat)
test_m1  = _m1_slice(test_feat)

print(f'Train : {len(train_feat):>7,} bars   {train_feat.index.min().date()} → {train_feat.index.max().date()}')
print(f'Val   : {len(val_feat):>7,} bars   {val_feat.index.min().date()} → {val_feat.index.max().date()}')
print(f'Test  : {len(test_feat):>7,} bars   {test_feat.index.min().date()} → {test_feat.index.max().date()}')

Timeframe : H1  (1h)
Embargo   : 200 bars
Loading M1 data …
Train : 110,790 bars   2003-05-19 → 2021-09-07
Val   :  13,474 bars   2021-10-01 → 2024-01-12
Test  :  13,674 bars   2024-02-06 → 2026-05-30


## 3 · Load model and evaluate on all three splits

In [4]:
import gymnasium as gym
from stable_baselines3 import PPO
from stable_baselines3.common.monitor import Monitor
from stable_baselines3.common.vec_env import DummyVecEnv, VecNormalize
from env_bracket import BracketTradingEnv


class _CaptureDoneWrapper(gym.Wrapper):
    """Saves equity_curve and trade_log the instant the episode ends,
    before DummyVecEnv's auto-reset wipes BracketTradingEnv.trades."""
    def __init__(self, env):
        super().__init__(env)
        self.saved_equity = None
        self.saved_trades = None

    def step(self, action):
        obs, reward, terminated, truncated, info = self.env.step(action)
        if terminated or truncated:
            inner = self.env
            while hasattr(inner, 'env'):
                inner = inner.env
            self.saved_equity = inner.equity_curve()
            self.saved_trades = inner.trade_log()
        return obs, reward, terminated, truncated, info


def _make_env(decision_df, m1_df):
    env = BracketTradingEnv(
        decision_df, m1_df, feature_cols,
        sl_atr_multipliers=CFG.sl_atr_multipliers,
        tp_r_multipliers=CFG.tp_r_multipliers,
        initial_equity=CFG.initial_equity,
        risk_fraction=CFG.risk_fraction,
        spread_price=CFG.spread_price,
        slippage_price=CFG.slippage_price,
        commission_per_trade=CFG.commission_per_trade,
        holding_penalty=CFG.holding_penalty,
        reward_mtm_weight=CFG.reward_mtm_weight,
        randomize_start=False,
    )
    return _CaptureDoneWrapper(Monitor(env))


def run_model_on_split(model_path, vecnorm_path, decision_df, m1_df, label='split'):
    """Evaluate a saved model on one full split. Returns (equity_df, trades_df)."""
    raw = DummyVecEnv([lambda df=decision_df, m=m1_df: _make_env(df, m)])

    if Path(vecnorm_path).exists():
        venv = VecNormalize.load(str(vecnorm_path), raw)
        venv.training    = False
        venv.norm_reward = False
    else:
        print(f'  Warning: vecnorm not found — obs unnormalized for {label}')
        venv = raw

    model = PPO.load(str(model_path), env=venv)

    obs  = venv.reset()
    done = [False]
    while not done[0]:
        action, _ = model.predict(obs, deterministic=True)
        obs, _, done, _ = venv.step(action)

    capture = venv.venv.envs[0]
    eq     = capture.saved_equity if capture.saved_equity is not None else pd.DataFrame()
    trades = capture.saved_trades if capture.saved_trades is not None else pd.DataFrame()

    ret = (eq['equity'].iloc[-1] / CFG.initial_equity - 1) * 100 if not eq.empty else 0.0
    print(f'  {label:<20}  trades={len(trades):>4}  return={ret:+.1f}%')
    return eq, trades


# ── Two checkpoints to compare ─────────────────────────────────────────────
# FINAL_MODEL   : last checkpoint after all training timesteps (set in cell 1
#                 from run_info.json).  No selection bias — purely the end state.
# BEST_VAL_MODEL: best-consistency checkpoint (min(train_eval_R, val_R) peak).
#
# FINAL_MODEL is already set correctly in cell 1; do NOT reassign it here.
BEST_VAL_MODEL = MODELS / 'best_model' / 'best_model.zip'

print(f'FINAL model     : {FINAL_MODEL}')
print(f'Best-val model  : {BEST_VAL_MODEL}')
print()

print('=== FINAL model (last checkpoint) ===')
final_train_eq, final_train_trades = run_model_on_split(FINAL_MODEL, VECNORM_PATH, train_feat, train_m1, 'Train')
final_val_eq,   final_val_trades   = run_model_on_split(FINAL_MODEL, VECNORM_PATH, val_feat,   val_m1,   'Val')
final_test_eq,  final_test_trades  = run_model_on_split(FINAL_MODEL, VECNORM_PATH, test_feat,  test_m1,  'Test')

if BEST_VAL_MODEL.exists():
    print('\n=== BEST-VAL model (best-consistency checkpoint) ===')
    bv_train_eq, bv_train_trades = run_model_on_split(BEST_VAL_MODEL, VECNORM_PATH, train_feat, train_m1, 'Train')
    bv_val_eq,   bv_val_trades   = run_model_on_split(BEST_VAL_MODEL, VECNORM_PATH, val_feat,   val_m1,   'Val')
    bv_test_eq,  bv_test_trades  = run_model_on_split(BEST_VAL_MODEL, VECNORM_PATH, test_feat,  test_m1,  'Test')
else:
    print('\nBest-val checkpoint not found — using final model for both.')
    bv_train_eq, bv_train_trades = final_train_eq, final_train_trades
    bv_val_eq,   bv_val_trades   = final_val_eq,   final_val_trades
    bv_test_eq,  bv_test_trades  = final_test_eq,  final_test_trades

# ── Promote MODEL_PATH results to primary variables for downstream cells ───
# MODEL_PATH (set in cell 1) = best_model.zip when it exists, else FINAL_MODEL.
# Downstream cells (sections 5–11) use train_eq / val_eq / test_eq; pointing
# them at MODEL_PATH's results means one toggle (MODEL_PATH in cell 1) controls
# the whole notebook.
if MODEL_PATH == BEST_VAL_MODEL:
    train_eq, train_trades = bv_train_eq, bv_train_trades
    val_eq,   val_trades   = bv_val_eq,   bv_val_trades
    test_eq,  test_trades  = bv_test_eq,  bv_test_trades
    print('\nDownstream primary → BEST-VAL checkpoint  (change MODEL_PATH in cell 1 to switch)')
else:
    train_eq, train_trades = final_train_eq, final_train_trades
    val_eq,   val_trades   = final_val_eq,   final_val_trades
    test_eq,  test_trades  = final_test_eq,  final_test_trades
    print('\nDownstream primary → FINAL checkpoint  (change MODEL_PATH in cell 1 to switch)')

print('\nDone.')

FINAL model     : models\ppo_H1_sl1-1.5-2_tp1-1.5-2-3_3000k_seed42.zip
Best-val model  : F:\CodeTrading\Code_trading_2026\34_RL_XAUUSD\models\best_model\best_model.zip

=== FINAL model (last checkpoint) ===
  Train                 trades=9232  return=+25.6%
  Val                   trades=1180  return=+24.3%
  Test                  trades=1248  return=+56.6%

=== BEST-VAL model (best-consistency checkpoint) ===
  Train                 trades=10925  return=-31.5%
  Val                   trades=1404  return=+30.5%
  Test                  trades=1487  return=+70.0%

Downstream primary → BEST-VAL checkpoint  (change MODEL_PATH in cell 1 to switch)

Done.


## 4 · Baseline evaluation on test (for comparison)

In [22]:
from baselines import evaluate_policy, make_trend_hold_policy, TrendHoldPolicyParams

sel_path = ROOT / 'outputs' / 'selected_policy.csv'
if sel_path.exists():
    sp = pd.read_csv(sel_path, index_col=0)
    bp = TrendHoldPolicyParams(
        threshold_atr=float(sp.loc['threshold_atr', 'value']),
        sl_idx=int(sp.loc['sl_idx', 'value']),
        tp_idx=int(sp.loc['tp_idx', 'value']),
    )
    print(f'Loaded baseline params: {bp}')
else:
    bp = TrendHoldPolicyParams()
    print('selected_policy.csv not found — using default baseline params.')

baseline_env = BracketTradingEnv(
    test_feat, test_m1, feature_cols,
    sl_atr_multipliers=CFG.sl_atr_multipliers,
    tp_r_multipliers=CFG.tp_r_multipliers,
    initial_equity=CFG.initial_equity,
    risk_fraction=CFG.risk_fraction,
    spread_price=CFG.spread_price,
    slippage_price=CFG.slippage_price,
    commission_per_trade=CFG.commission_per_trade,
    holding_penalty=CFG.holding_penalty,
    reward_mtm_weight=CFG.reward_mtm_weight,
)
baseline_eq, baseline_trades, _ = evaluate_policy(
    baseline_env, make_trend_hold_policy(bp),
    initial_equity=CFG.initial_equity,
    periods_per_year=CFG.periods_per_year,
)
print(f'Baseline trades on test: {len(baseline_trades)}')

Loaded baseline params: TrendHoldPolicyParams(threshold_atr=0.3, sl_idx=2, tp_idx=3)
Baseline trades on test: 505


## 5 · Performance summary table

In [23]:
from evaluate import full_report
from visualize import plot_metrics_table, save_html

def _rep(eq, trades):
    r = full_report(eq, trades,
                    initial_equity=CFG.initial_equity,
                    periods_per_year=CFG.periods_per_year)
    return r['value'].to_dict()

# Final model across all splits + baseline
metrics_final = {
    'Train (final)' : _rep(final_train_eq, final_train_trades),
    'Val   (final)' : _rep(final_val_eq,   final_val_trades),
    'Test  (final)' : _rep(final_test_eq,  final_test_trades),
    'Baseline'      : _rep(baseline_eq,    baseline_trades),
}

# Best-val checkpoint (val score inflated — used to select it; test is honest)
metrics_bestval = {
    'Train (best-val)' : _rep(bv_train_eq, bv_train_trades),
    'Val   (best-val)' : _rep(bv_val_eq,   bv_val_trades),
    'Test  (best-val)' : _rep(bv_test_eq,  bv_test_trades),
    'Baseline'         : _rep(baseline_eq, baseline_trades),
}

# Primary metrics follow MODEL_PATH (set in cell 1)
metrics = metrics_bestval if MODEL_PATH == BEST_VAL_MODEL else metrics_final

fig = plot_metrics_table(metrics_final, title='FINAL model — Performance across splits')
save_html(fig, OUT / '00a_metrics_final.html')
fig.show()

fig = plot_metrics_table(metrics_bestval, title='BEST-VAL checkpoint — Performance across splits')
save_html(fig, OUT / '00b_metrics_bestval.html')
fig.show()

## 6 · Equity curves — all splits on one chart

In [24]:
from visualize import plot_equity_comparison, plot_equity_and_drawdown, plot_insample_oos_equity

# Final model: normalised equity curves
fig = plot_equity_comparison(
    {'Train': final_train_eq, 'Val': final_val_eq, 'Test': final_test_eq, 'Baseline': baseline_eq},
    title='FINAL model — Equity curves (normalised to 100)',
)
save_html(fig, OUT / '01a_equity_final.html')
fig.show()

# Best-val checkpoint: normalised equity curves
fig = plot_equity_comparison(
    {'Train': bv_train_eq, 'Val': bv_val_eq, 'Test': bv_test_eq, 'Baseline': baseline_eq},
    title='BEST-VAL checkpoint — Equity curves (normalised to 100)',
)
save_html(fig, OUT / '01b_equity_bestval.html')
fig.show()

In [25]:
# Chained in-sample → out-of-sample view
fig = plot_insample_oos_equity(
    {'Train': train_eq, 'Val': val_eq, 'Test': test_eq},
    initial_equity=CFG.initial_equity,
    title='RL Agent — In-sample → Out-of-sample equity (chained)',
)
save_html(fig, OUT / '01b_equity_insample_oos.html')
fig.show()

In [9]:
fig = plot_equity_and_drawdown(test_eq, title='Test split — Equity & Drawdown')
save_html(fig, OUT / '02_test_equity_drawdown.html')
fig.show()

## 7 · Trade analysis — test split

In [10]:
from visualize import plot_r_distribution
fig = plot_r_distribution(test_trades, title='Test — Realized R-multiple distribution')
save_html(fig, OUT / '03_r_distribution_test.html')
fig.show()

In [11]:
from visualize import plot_monthly_pnl
fig = plot_monthly_pnl(test_trades, title='Test — Monthly P&L (R-multiples)')
save_html(fig, OUT / '04_monthly_pnl_test.html')
fig.show()

F:\CodeTrading\Code_trading_2026\34_RL_XAUUSD\visualize.py:375: UserWarning: Converting to PeriodArray/Index representation will drop timezone information.
  tr["month"] = pd.to_datetime(tr["exit_time"]).dt.to_period("M").astype(str)


In [12]:
from visualize import plot_exit_breakdown
fig = plot_exit_breakdown(test_trades, title='Test — Exit reason breakdown')
save_html(fig, OUT / '05_exit_breakdown_test.html')
fig.show()

## 8 · Agent behaviour analysis

In [13]:
from visualize import plot_bracket_usage
all_trades = pd.concat([train_trades, val_trades, test_trades], ignore_index=True)
fig = plot_bracket_usage(
    all_trades,
    sl_atr_multipliers=CFG.sl_atr_multipliers,
    tp_r_multipliers=CFG.tp_r_multipliers,
    title='Agent bracket selection — SL × TP heatmap (all splits)',
)
save_html(fig, OUT / '06_bracket_heatmap.html')
fig.show()

In [14]:
from visualize import plot_entry_timing
fig = plot_entry_timing(test_trades, title='Test — Entry timing (hour × weekday)')
save_html(fig, OUT / '07_entry_timing_test.html')
fig.show()

## 9 · Rolling Sharpe — test split

In [15]:
from visualize import plot_rolling_metrics
window = max(20, len(test_eq) // 15)
fig = plot_rolling_metrics(
    test_eq, window=window,
    periods_per_year=CFG.periods_per_year,
    title=f'Test — Equity + rolling Sharpe (window = {window} bars)',
)
save_html(fig, OUT / '08_rolling_sharpe_test.html')
fig.show()

## 10 · Candlestick chart with test trades

In [16]:
from visualize import plot_trades_on_chart
BARS_TO_SHOW = 300
fig = plot_trades_on_chart(
    test_feat, test_trades, n=BARS_TO_SHOW,
    title=f'Test — last {BARS_TO_SHOW} bars with trades',
)
save_html(fig, OUT / '09_candles_test_trades.html')
fig.show()

## 11 · Feature correlation — test period

In [17]:
from visualize import plot_feature_correlation
fig = plot_feature_correlation(test_feat, feature_cols,
                               title='Test period — Feature correlation heatmap')
save_html(fig, OUT / '10_feature_correlation_test.html')
fig.show()

## 12 · Val vs Test R-distribution (overfitting check)

In [18]:
import plotly.graph_objects as go
from plotly.subplots import make_subplots

def _wr(t): return 100 * (t['r_mult'] > 0).mean() if len(t) else 0

fig = make_subplots(rows=1, cols=2,
    subplot_titles=(
        f'Val   WR={_wr(val_trades):.1f}%  n={len(val_trades)}',
        f'Test  WR={_wr(test_trades):.1f}%  n={len(test_trades)}',
    ))

for col, (trades, _name) in enumerate([(val_trades, 'Val'), (test_trades, 'Test')], start=1):
    r = trades['r_mult'].astype(float) if len(trades) else pd.Series(dtype=float)
    fig.add_trace(go.Histogram(x=r[r > 0],  name='Win',  marker_color='rgba(0,200,83,0.70)',
                               xbins=dict(size=0.25), showlegend=(col==1)), row=1, col=col)
    fig.add_trace(go.Histogram(x=r[r <= 0], name='Loss', marker_color='rgba(213,0,0,0.70)',
                               xbins=dict(size=0.25), showlegend=(col==1)), row=1, col=col)
    fig.add_vline(x=0, line_color='black', line_width=1, row=1, col=col)

fig.update_layout(title='Val vs Test — R-distribution (overfitting check)',
                  barmode='overlay', height=420, template='plotly_white')
save_html(fig, OUT / '11_val_vs_test_r_dist.html')
fig.show()

## 13 · Summary print

In [19]:
print('='*65)
print(f'Model  : {MODEL_PATH.name}')
print(f'Charts : {OUT}')
print('='*65)
for name, m in metrics.items():
    ret = m.get('total_return_pct', float('nan'))
    sh  = m.get('sharpe_like',      float('nan'))
    dd  = m.get('max_drawdown_pct', float('nan'))
    pf  = m.get('profit_factor',    float('nan'))
    nt  = m.get('n_trades', 0)
    print(f'{name:<10} ret={ret:+7.1f}%  Sharpe={sh:+5.2f}  '
          f'MaxDD={dd:+6.1f}%  PF={pf:.2f}  n={nt}')

Model  : best_model.zip
Charts : F:\CodeTrading\Code_trading_2026\34_RL_XAUUSD\outputs\notebook
Train (best-val) ret=  -31.5%  Sharpe=-0.07  MaxDD= -54.0%  PF=0.99  n=10925.0
Val   (best-val) ret=  +30.5%  Sharpe=+0.88  MaxDD= -21.1%  PF=1.08  n=1404.0
Test  (best-val) ret=  +70.0%  Sharpe=+1.55  MaxDD= -10.3%  PF=1.14  n=1487.0
Baseline   ret=  +33.7%  Sharpe=+1.06  MaxDD= -10.2%  PF=1.17  n=505.0
